In [1]:
import osmnx as ox
import networkx as nx
import geopandas as gpd

G = ox.load_graphml(
    "turku_bike_network_floodinfo.graphml",
    edge_dtypes={
        "flooded": lambda x: str(x).lower() == "true"
    }
)

print(f"Nodes: {G.number_of_nodes()}")
print(f"Edges: {G.number_of_edges()}")
print(f"CRS: {G.graph['crs']}")

Nodes: 33813
Edges: 58752
CRS: epsg:4326


In [2]:
flooded_count = sum(
    data.get("flooded", False)
    for _, _, _, data in G.edges(keys=True, data=True)
)

print(f"Flooded edges: {flooded_count}")

Flooded edges: 19673


In [3]:
G_normal = G
G_flooded = G.copy()

edges_to_remove = [
    (u, v, key)
    for u, v, key, data in G_flooded.edges(
        keys=True, data=True
    )
    if data.get("flooded", False)
]

G_flooded.remove_edges_from(edges_to_remove)

print("Normal edges:", G_normal.number_of_edges())
print("Flooded edges:", G_flooded.number_of_edges())

Normal edges: 58752
Flooded edges: 39079


In [40]:
# Replace with two actual locations in your study area

start_lon = 22.25
start_lat = 60.46

school_lon = 22.2810684
school_lat = 60.4466903

In [20]:
print(G.graph["crs"])

epsg:4326


In [42]:
from pyproj import Transformer

transformer = Transformer.from_crs(
    "EPSG:4326",
    G.graph["crs"],
    always_xy=True
)

start_x, start_y = transformer.transform(
    start_lon, start_lat
)

school_x, school_y = transformer.transform(
    school_lon, school_lat
)

In [43]:
start_node = ox.distance.nearest_nodes(
    G_normal,
    X=start_x,
    Y=start_y
)

school_node = ox.distance.nearest_nodes(
    G_normal,
    X=school_x,
    Y=school_y
)

print("Start node:", start_node)
print("School node:", school_node)

Start node: 8995729520
School node: 176712112


In [44]:
# Normal shortest route
try:
    route_normal = nx.shortest_path(
        G_normal,
        source=start_node,
        target=school_node,
        weight="length"
    )
except nx.NetworkXNoPath:
    route_normal = None

# Flood-avoiding shortest route
try:
    route_flooded = nx.shortest_path(
        G_flooded,
        source=start_node,
        target=school_node,
        weight="length"
    )
except nx.NetworkXNoPath:
    route_flooded = None

print("Normal route:", route_normal is not None)
print("Flood-avoiding route:", route_flooded is not None)

Normal route: True
Flood-avoiding route: False


In [47]:
if route_normal is not None:
    normal_gdf = ox.routing.route_to_gdf(
        G_normal, route_normal, weight="length"
    )

if route_flooded is not None:
    flooded_gdf = ox.routing.route_to_gdf(
        G_flooded, route_flooded, weight="length"
    )

In [48]:
if route_normal is not None:
    normal_length = normal_gdf["length"].sum()
    print(f"Normal route: {normal_length:.0f} m")

if route_flooded is not None:
    flooded_length = flooded_gdf["length"].sum()
    print(f"Flood-avoiding route: {flooded_length:.0f} m")

Normal route: 2844 m


In [24]:
import networkx as nx

print("Nodes:", G_normal.number_of_nodes())
print("Edges:", G_normal.number_of_edges())

print(
    "Weakly connected components:",
    nx.number_weakly_connected_components(G_normal)
)

print(
    "Strongly connected components:",
    nx.number_strongly_connected_components(G_normal)
)

Nodes: 33813
Edges: 58752
Weakly connected components: 9856
Strongly connected components: 9917


In [25]:
# Is there a path between them?
print(
    "Path ignoring direction:",
    nx.has_path(G_normal.to_undirected(), start_node, school_node)
)

print(
    "Directed path:",
    nx.has_path(G_normal, start_node, school_node)
)

Path ignoring direction: False
Directed path: False


In [26]:
components = list(
    nx.weakly_connected_components(G_normal)
)

components = sorted(
    components,
    key=len,
    reverse=True
)

largest_component = components[0]

print("Largest component:", len(largest_component))
print("Start in largest:", start_node in largest_component)
print("School in largest:", school_node in largest_component)

Largest component: 23309
Start in largest: True
School in largest: False


In [17]:
# Largest strongly connected component
largest_scc = max(
    nx.strongly_connected_components(G_normal),
    key=len
)

G_test = G_normal.subgraph(largest_scc).copy()

# Find closest nodes within this component
start_node_test = ox.distance.nearest_nodes(
    G_test,
    X=start_x,
    Y=start_y
)

school_node_test = ox.distance.nearest_nodes(
    G_test,
    X=school_x,
    Y=school_y
)

# Calculate test route
route_test = nx.shortest_path(
    G_test,
    start_node_test,
    school_node_test,
    weight="length"
)

print("Route found!")
print("Number of nodes in route:", len(route_test))

Route found!
Number of nodes in route: 53


In [18]:
import geopandas as gpd
from shapely.geometry import Point

start_point = Point(
    G_normal.nodes[start_node]["x"],
    G_normal.nodes[start_node]["y"]
)

school_point = Point(
    G_normal.nodes[school_node]["x"],
    G_normal.nodes[school_node]["y"]
)

points = gpd.GeoDataFrame(
    {
        "location": ["Start", "School"],
        "geometry": [start_point, school_point]
    },
    crs=G_normal.graph["crs"]
)

m = ox.graph_to_gdfs(
    G_normal,
    nodes=False
).to_crs(4326).explore(
    color="grey",
    style_kwds={"weight": 1},
    tiles="CartoDB positron"
)

points.to_crs(4326).explore(
    m=m,
    column="location",
    categorical=True,
    marker_kwds={"radius": 7},
    legend=True
)

m

In [27]:
print("Start:", start_node)
print("School:", school_node)

print(
    "Connected ignoring direction:",
    nx.has_path(G_normal.to_undirected(), start_node, school_node)
)

print(
    "Connected with direction:",
    nx.has_path(G_normal, start_node, school_node)
)

Start: 8995729520
School: 4753319608
Connected ignoring direction: False
Connected with direction: False


In [28]:
components = sorted(
    nx.weakly_connected_components(G_normal),
    key=len,
    reverse=True
)

sizes = [len(c) for c in components]

print("10 largest components:", sizes[:10])

print(
    "Percentage of nodes in largest component:",
    round(sizes[0] / G_normal.number_of_nodes() * 100, 1),
    "%"
)

10 largest components: [23309, 12, 10, 8, 8, 8, 8, 7, 7, 7]
Percentage of nodes in largest component: 68.9 %


In [29]:
largest_component = components[0]

print("Start in largest:", start_node in largest_component)
print("School in largest:", school_node in largest_component)

Start in largest: True
School in largest: False


In [30]:
for name, node in [
    ("Start", start_node),
    ("School", school_node)
]:
    component = next(
        c for c in components if node in c
    )

    print(
        f"{name}: component with {len(component)} nodes"
    )

Start: component with 23309 nodes
School: component with 4 nodes


In [31]:
def network_summary(G, name):
    components = list(nx.weakly_connected_components(G))
    largest = max(components, key=len)

    print(f"\n{name}")
    print("Nodes:", G.number_of_nodes())
    print("Edges:", G.number_of_edges())
    print("Components:", len(components))
    print(
        "Largest component (%):",
        round(len(largest) / G.number_of_nodes() * 100, 1)
    )

network_summary(G_original, "Original network")
network_summary(G_normal, "Cleaned network")

NameError: name 'G_original' is not defined

In [32]:
print("Largest 10 component sizes:", sizes[:10])

print(
    "Largest component percentage:",
    round(sizes[0] / G_normal.number_of_nodes() * 100, 1)
)

print("Isolated nodes:", nx.number_of_isolates(G_normal))

print("Start in largest:", start_node in largest_component)
print("School in largest:", school_node in largest_component)

Largest 10 component sizes: [23309, 12, 10, 8, 8, 8, 8, 7, 7, 7]
Largest component percentage: 68.9
Isolated nodes: 9432
Start in largest: True
School in largest: False


In [33]:
import networkx as nx
import osmnx as ox

G_clean = G_normal.copy()

# Remove nodes that have no edges
isolated_nodes = list(nx.isolates(G_clean))

G_clean.remove_nodes_from(isolated_nodes)

print("Removed isolated nodes:", len(isolated_nodes))
print("Remaining nodes:", G_clean.number_of_nodes())
print(
    "Remaining components:",
    nx.number_weakly_connected_components(G_clean)
)

Removed isolated nodes: 9432
Remaining nodes: 24381
Remaining components: 424


In [34]:
start_node = ox.distance.nearest_nodes(
    G_clean, X=start_x, Y=start_y
)

school_node = ox.distance.nearest_nodes(
    G_clean, X=school_x, Y=school_y
)

print(
    "Connected:",
    nx.has_path(
        G_clean.to_undirected(),
        start_node,
        school_node
    )
)

Connected: False


In [35]:
# Identify the largest weakly connected component
largest_component = max(
    nx.weakly_connected_components(G_clean),
    key=len
)

# Create a graph containing only that component
G_main = G_clean.subgraph(largest_component).copy()

# Find the nearest nodes again
start_node = ox.distance.nearest_nodes(
    G_main, X=start_x, Y=start_y
)

school_node = ox.distance.nearest_nodes(
    G_main, X=school_x, Y=school_y
)

print(
    "Directed path exists:",
    nx.has_path(G_main, start_node, school_node)
)

Directed path exists: True


In [36]:
from shapely.geometry import Point
import geopandas as gpd

school_point = gpd.GeoSeries(
    [Point(school_x, school_y)],
    crs=G_main.graph["crs"]
).to_crs(3067)

school_node_point = gpd.GeoSeries(
    [Point(
        G_main.nodes[school_node]["x"],
        G_main.nodes[school_node]["y"]
    )],
    crs=G_main.graph["crs"]
).to_crs(3067)

distance = school_point.distance(school_node_point).iloc[0]

print(f"School snapping distance: {distance:.1f} metres")

School snapping distance: 48.9 metres


In [45]:
G_normal = G_main.copy()

G_flooded = G_main.copy()

flooded_edges = [
    (u, v, key)
    for u, v, key, data in G_flooded.edges(
        keys=True, data=True
    )
    if data.get("flooded", False)
]

G_flooded.remove_edges_from(flooded_edges)

# Normal shortest route
route_normal = nx.shortest_path(
    G_normal,
    start_node,
    school_node,
    weight="length"
)

# Flood-avoiding route
try:
    route_flooded = nx.shortest_path(
        G_flooded,
        start_node,
        school_node,
        weight="length"
    )
except nx.NetworkXNoPath:
    route_flooded = None

print("Normal route found:", route_normal is not None)
print("Flood route found:", route_flooded is not None)

Normal route found: True
Flood route found: False
